In [96]:
import sys
sys.path.insert(1, '..')

In [97]:
import pandas as pd
from os import listdir

In [324]:
import numpy as np

In [98]:
from utils.countryconverter import *

In [99]:
IMAP_DATAPATH = "../../data/raw/fdi/imap"

In [100]:
UNCTAD_DATAPATH = "../../data/raw/fdi/unctad"
IMF_DATAPATH='../../data/raw/fdi/imf'

## Investment Map

In [101]:
def get_already_parsed(source='investmentmap'):
    dir_files = listdir(IMAP_DATAPATH)
    already_parsed = []
    for i in dir_files:
        if i[0] == '.': continue
        already_parsed += i,
    already_parsed_isoid = [(x.split('_')[1],x.split('_')[3]) for x in already_parsed]
    return already_parsed_isoid

In [102]:
imap = listdir(IMAP_DATAPATH)#.remove('.ipynb_checkpoints')
imap.remove(".ipynb_checkpoints")

In [103]:
wrong_fdi = []
dfs = {}
for fdifile in imap:
    try:
        country_name = fdifile.split('_')[2]
        direction = fdifile.split('_')[0][3:5]
        df=pd.read_excel(IMAP_DATAPATH + '/' + fdifile)
        df['Country'] = country_name
        df['direction'] = direction
        df=df.set_index(['Country', 'Partner Country', 'direction'])
        df=pd.DataFrame(df.stack())
        df.index.names=['Country', 'Partner Country', 'direction', 'year']
        dfs[fdifile]=df
    except ValueError:
        wrong_fdi += fdifile,

In [104]:
imap_df = pd.concat(dfs)

In [105]:
imap_df=imap_df.reset_index().drop(['level_0'], axis=1).rename({0:'value'}, axis=1)

In [106]:
imap_df.to_csv("imap_data_.csv")

## UNCTAD

In [107]:
country_isos = pd.read_csv("https://docs.google.com/spreadsheets/d/1ayIh8JK-Io3EvhwctDcIbwelEBoloyEY3Fz1nx0RTyg/export?gid=0&format=csv")
#try_country()
iso_to_name = dict(country_isos[['Alpha3_Code', 'STATE_en_UN']].values)

In [108]:
unctad = listdir(UNCTAD_DATAPATH)#.remove('.ipynb_checkpoints')
unctad.remove(".ipynb_checkpoints")

In [109]:
def curate_table(df):
    return df_curated

def fill_country(x):
    if 'Reporting economy' in x.index:
        return x['Reporting economy']
    for i in range(5, 1, -1):
        print(x.index)
        if pd.notna(x[f'Unnamed: {i}']):
            return x[f'Unnamed: {i}']
    return None

In [110]:
dfs = {}
for iso_a3 in iso_to_name.keys():
    for direction in ['instock', 'outstock']:
        country_name = iso_to_name[iso_a3]
        print(iso_a3, country_name, direction)
        try:
            unctad_stock = pd.read_excel(UNCTAD_DATAPATH+'/'+f'fdi_{iso_a3}.xls', sheet_name=direction, skiprows=4)
        except FileNotFoundError:
            continue
        unctad_stock['Partner Country']=unctad_stock.apply(fill_country, axis=1)
        unctad_stock.dropna(subset='Partner Country', inplace=True)
        unctad_stock=unctad_stock[unctad_stock.columns.drop(list(unctad_stock.filter(regex='Unnamed')))]
        if 'Region / economy' in unctad_stock.columns:
            unctad_stock=unctad_stock.drop('Region / economy', axis=1)
        unctad_stock=convert_country_df(data=unctad_stock, data_id_col='Partner Country', warning = True, replace_missing=None)
        unctad_stock=convert_country_df(data=unctad_stock, data_id_col='Partner Country', warning = True, replace_missing=None)
        unctad_stock=convert_country_df(data=unctad_stock, data_id_col='Partner Country', warning = True, replace_missing=None)
        unctad_stock=unctad_stock.replace("None", None).dropna(subset='Partner Country')
        unctad_stock['Country']=country_name
        unctad_stock['direction']=direction[0:2]
        unctad_stock=unctad_stock.reset_index(drop=True)#.set_index(['Country', 'Partner Country', 'direction'])
        try:
            unctad_stock=unctad_stock.drop('Reporting economy', axis=1)
        except KeyError:
            continue
        unctad_stock.columns=unctad_stock.columns.astype(str)
        if iso_a3 in dfs:
            df_test_2 = unctad_stock
            dfs[iso_a3] = pd.concat([unctad_stock,dfs[iso_a3]])
        else:
            df_test_1 = unctad_stock
            dfs[iso_a3] = unctad_stock

AFG Afghanistan instock


/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Source:  UNCTAD FDI/TNC database., replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Note:  Data are based on information reported by the economies listed above., replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")


Pakistan Pakistan
Italy Italy
Denmark Denmark
United States United States
Turkey Türkiye
Source:  UNCTAD FDI/TNC database. None
China China, People's Republic of
Note:  Data are based on information reported by the economies listed above. None


/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier None, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")


Pakistan Pakistan
Türkiye Türkiye
Italy Italy
Denmark Denmark
United States United States
None None
China, People's Republic of China, People's Republic of


...

/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Source:  UNCTAD FDI/TNC database., replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Note:  Data are based on information reported by the economies listed above., replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")


Italy Italy
Botswana Botswana
United States United States
Malawi Malawi
Source:  UNCTAD FDI/TNC database. None
Cyprus Cyprus
United Republic of Tanzania United Republic of Tanzania
South Africa South Africa
Note:  Data are based on information reported by the economies listed above. None
Zambia Zambia


/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier None, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")


Italy Italy
Botswana Botswana
United States United States
Malawi Malawi
Cyprus Cyprus
United Republic of Tanzania United Republic of Tanzania
South Africa South Africa
None None
Zambia Zambia
Italy Italy
Botswana Botswana
United States United States
Malawi Malawi
Cyprus Cyprus
United Republic of Tanzania United Republic of Tanzania
South Africa South Africa
None None
Zambia Zambia


/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier None, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")


In [111]:
unctad_data=pd.concat(dfs)

In [112]:
unctad_df = pd.DataFrame(unctad_data.set_index(['Country', 'Partner Country', 'direction']).stack())

In [113]:
unctad_df=unctad_df.reset_index().rename({0:'value', 'level_3':'year'}, axis=1)

In [114]:
unctad_data.to_csv('unctad_data_.csv')#.head(20)#['Unnamed: 5'].dropna()

## IMF

In [115]:
imf = listdir(IMF_DATAPATH)#.remove('.ipynb_checkpoints')
#imap.remove(".ipynb_checkpoints")

In [255]:
imf

['in2021.xlsx',
 'out2016.xlsx',
 'out2017.xlsx',
 'out2018.xlsx',
 'out2019.xlsx',
 'out2020.xlsx',
 'out2021.xlsx',
 'out2022.xlsx',
 'out2023.xlsx',
 'in2023.xlsx',
 'in2022.xlsx',
 'in2018.xlsx',
 'in2020.xlsx',
 'in2019.xlsx',
 'in2017.xlsx',
 'in2016.xlsx',
 'out2015.xlsx',
 'out2014.xlsx',
 'out2013.xlsx',
 'out2012.xlsx',
 'out2011.xlsx',
 'out2010.xlsx',
 'out2009.xlsx',
 'in2009.xlsx',
 'in2010.xlsx',
 'in2011.xlsx',
 'in2012.xlsx',
 'in2013.xlsx',
 'in2014.xlsx',
 'in2015.xlsx']

In [214]:
dfs=[]
for dir in ['in', 'out']:
    for year in range(2009, 2024):
        df = pd.read_excel(f'{IMF_DATAPATH}/{dir}{year}.xlsx', skiprows=3).replace('C', None)
        if dir=='in':
            df=pd.DataFrame(df.set_index('Investment from:').unstack()).reset_index().rename({'level_0':'Country', 'Investment from:':'Partner Country',0:'value'}, axis=1)
        if dir=='out':
            df=pd.DataFrame(df.set_index('Investment in:').unstack()).reset_index().rename({'level_0':'Country', 'Investment in:':'Partner Country',0:'value'}, axis=1)
        df['direction']='in' if dir=='in' else 'ou'
        df['year']=year
        print(df.head())
        dfs+=df,
df=pd.concat(dfs)
df=convert_country_df(data=df, data_id_col='Country', warning=True, replace_missing=None)
df=convert_country_df(data=df, data_id_col='Partner Country', warning=True, replace_missing=None)
        

   Country               Partner Country value direction  year
0  Albania  Afghanistan, Islamic Rep. of   NaN        in  2009
1  Albania                       Albania   NaN        in  2009
2  Albania                       Algeria   NaN        in  2009
3  Albania                American Samoa   NaN        in  2009
4  Albania      Andorra, Principality of   NaN        in  2009
   Country               Partner Country value direction  year
0  Albania  Afghanistan, Islamic Rep. of   NaN        in  2010
1  Albania                       Albania   NaN        in  2010
2  Albania                       Algeria   NaN        in  2010
3  Albania                American Samoa   NaN        in  2010
4  Albania      Andorra, Principality of   NaN        in  2010
   Country               Partner Country value direction  year
0  Albania  Afghanistan, Islamic Rep. of   NaN        in  2011
1  Albania                       Albania   NaN        in  2011
2  Albania                       Algeria   NaN        i

/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier China, P.R.: Hong Kong, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Total Investment, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier West Bank and Gaza, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Curaçao, Kingdom of the Netherlands, replacing with None
  if warning: wa

Suriname Suriname
Netherlands, The Netherlands
Estonia, Rep. of Estonia
New Zealand New Zealand
Israel Israel
Albania Albania
Japan Japan
Nigeria Nigeria
China, P.R.: Hong Kong None
South Africa South Africa
Cabo Verde Cabo Verde
Solomon Islands Solomon Islands
Total Investment None
Russian Federation Russian Federation
Mali Mali
Armenia, Rep. of Armenia
Venezuela, Rep. Bolivariana de Venezuela (Bolivarian Republic of)
Türkiye, Rep. of Türkiye
Germany Germany
Belgium Belgium
Slovenia, Rep. of Slovenia
West Bank and Gaza None
Malaysia Malaysia
Serbia, Rep. of Serbia
Kazakhstan, Rep. of Kazakhstan
Bolivia Bolivia (Plurinational State of)
Belarus, Rep. of Belarus
Bahrain, Kingdom of Bahrain
Curaçao, Kingdom of the Netherlands None
Guinea-Bissau Guinea-Bissau
Samoa Samoa
Rwanda Rwanda
Croatia, Rep. of Croatia
Guinea Guinea
Bangladesh Bangladesh
Niger Niger
Panama Panama
Fiji, Rep. of Fiji
Iceland Iceland
Georgia Georgia
Guatemala Guatemala
Myanmar Myanmar
Senegal Senegal
Palau, Rep. of Pal

/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Northern Mariana Islands, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Data extracted from IMF Data Warehouse on:3/22/2025 11:14:28 AM, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning: Unknown identifier Data extracted from IMF Data Warehouse on:3/22/2025 11:25:52 AM, replacing with None
  if warning: warnings.warn(f"Unknown identifier {country}, replacing with {replace_missing}")
/home/alex-server/Sync/Работа/Code/phd_thesis/code/data_handling/../utils/countryconverter.py:83: UserWarning

Suriname Suriname
Netherlands, The Netherlands
Estonia, Rep. of Estonia
New Zealand New Zealand
Northern Mariana Islands None
Israel Israel
Albania Albania
Japan Japan
Data extracted from IMF Data Warehouse on:3/22/2025 11:14:28 AM None
Nigeria Nigeria
Data extracted from IMF Data Warehouse on:3/22/2025 11:25:52 AM None
Data extracted from IMF Data Warehouse on:3/22/2025 11:25:00 AM None
China, P.R.: Hong Kong None
South Africa South Africa
St. Vincent and the Grenadines Saint Vincent and the Grenadines
Cabo Verde Cabo Verde
Data extracted from IMF Data Warehouse on:3/22/2025 11:27:21 AM None
Gabon Gabon
Niue None
Solomon Islands Solomon Islands
Data extracted from IMF Data Warehouse on:3/22/2025 11:17:57 AM None
Russian Federation Russian Federation
Data extracted from IMF Data Warehouse on:3/22/2025 11:16:15 AM None
Mali Mali
Holy See None
Libya Libya
French Polynesia None
Armenia, Rep. of Armenia
Venezuela, Rep. Bolivariana de Venezuela (Bolivarian Republic of)
Tuvalu Tuvalu
Liechte

In [215]:
df = df.astype(str)

In [216]:
df['Country'].unique()

array(['Albania', 'Algeria', 'Argentina', 'Armenia', 'None', 'Australia',
       'Austria', 'Azerbaijan', 'Bahrain', 'Bangladesh', 'Barbados',
       'Belarus', 'Belgium', 'Benin', 'Bhutan',
       'Bolivia (Plurinational State of)', 'Bosnia and Herzegovina',
       'Botswana', 'Brazil', 'Brunei Darussalam', 'Bulgaria',
       'Burkina Faso', 'Cabo Verde', 'Cambodia', 'Canada', 'Chile',
       "China, People's Republic of", 'Costa Rica', "Côte d'Ivoire",
       'Croatia', 'Cyprus', 'Czechia', 'Denmark', 'El Salvador',
       'Estonia', 'Fiji', 'Finland', 'France', 'Georgia', 'Germany',
       'Ghana', 'Greece', 'Guatemala', 'Guinea', 'Guinea-Bissau',
       'Honduras', 'Hungary', 'Iceland', 'India', 'Indonesia', 'Ireland',
       'Israel', 'Italy', 'Japan', 'Jordan', 'Kazakhstan', 'Kiribati',
       'Republic of Korea', 'Kuwait', 'Kyrgyzstan', 'Latvia', 'Lebanon',
       'Lithuania', 'Luxembourg', 'Republic of North Macedonia',
       'Madagascar', 'Malaysia', 'Mali', 'Malta', 'Mauriti

In [217]:
_=df[df['Country']=='Czechia']

In [218]:
_=_[_['year']=='2015']

In [219]:
_=_[_['direction']=='out']

In [220]:
_=_[_['Partner Country']=='Netherlands']

In [221]:
_

,Country,Partner Country,value,direction,year


### Merging

In [222]:
df_full = imap_df.merge(unctad_df, on = ['Country', 'Partner Country', 'direction', 'year'], suffixes=['_imap', '_unctad'], how='outer')

In [223]:
df_full=df_full.merge(df, on = ['Country', 'Partner Country', 'direction', 'year'], suffixes=['', '_imf'], how='outer')

In [224]:
df_full=df_full.rename({'value':'value_imf'}, axis=1)

In [225]:
df_ou = df_full[df_full['direction']=='ou']
df_in = df_full[df_full['direction']=='in']

In [226]:
# Reorganizaing in data to out format
df_in = df_in.rename({'Country':'Partner Country', 'Partner Country':'Country', 'value_imap':'value_imap_inmirror', 'value_unctad':'value_unctad_inmirror', 'value_imf':'value_imf_inmirror'}, axis=1)
df_in['direction'] = 'ou'

In [311]:
def check_consistency(data_series):
    value = None
    options = {}
    for i in ['value_imap', 'value_unctad', 'value_imap_inmirror', 'value_unctad_inmirror', 'value_imf', 'value_imf_inmirror']:
        if data_series[i] == '..':
            data_series[i] = None
        if not isinstance(data_series[i], float) and pd.notna(data_series[i]) and data_series[i] != 'None':
            data_series[i] = float(data_series[i])
        if pd.notna(data_series[i]) and value is None:
            value = data_series[i]
            if value != 'None':
                options[i] = data_series[i]
        elif data_series[i] == 'None':
            value = None
        elif pd.notna(data_series[i]):
            options[i] = data_series[i]
    if len(options) > 1: 
        if len(options) == 4:
            candidate_option = []
            largest_diff = 9999999
            for i, option in enumerate(options.values()):
                if i == 0: continue
                diff = abs(option - list(options.values())[0])
                if diff < largest_diff:
                    largest_diff = diff
            if largest_diff < 5:
                return sorted(list(options.values()))[1]
            for i, option in enumerate(options.values()):
                for j, option2 in enumerate(options.values()):
                    if i==j: continue
                    if abs(option - option2)<5 and not ((option2,option) in candidate_option):
                        candidate_option += (option,option2),
            if len(candidate_option) == 1:
                return abs(candidate_option[0][0] + candidate_option[0][1]) / 2
            else:
                min_diff = 999999
                min_candidate = ()
                for candidate in candidate_option:
                    diff = abs(float(candidate[0])-float(candidate[1]))
                    if diff < min_diff:
                        min_diff = diff
                        min_candidate = candidate
                if len(min_candidate) > 0:
                    return abs(min_candidate[0] + min_candidate[1]) / 2
            return (sorted(list(options.values()))[2] + sorted(list(options.values()))[1]) / 2
            print(f"conflict: {options}, options: {candidate_option}")
        elif len(options) == 2:
            if list(options.values())[0] == list(options.values())[1]:
                return value
            if 'value_imap_inmirror' in options and 'value_imap' in options:
                return options['value_imap_inmirror'] if options['value_imap_inmirror']>options['value_imap'] else options['value_imap']
            if list(options.values())[0] == 0:
                return list(options.values())[1]
            if list(options.values())[1] == 0:
                return list(options.values())[0]
            #print(options)
            if (abs(list(options.values())[0] - list(options.values())[1]) < 5) or ((abs(list(options.values())[0]/list(options.values())[1]) < 1.15) and (abs(list(options.values())[0]/list(options.values())[1]) > 0.85)):
                return (list(options.values())[0] + list(options.values())[1]) / 2
            if ('value_imap_inmirror' in options or 'value_imap' in options) and ('value_unctad' in options or 'value_unctad_inmirror' in options):
                return options['value_unctad'] if 'value_unctad' in options else options['value_unctad_inmirror']
            if ('value_imap_inmirror' in options or 'value_imap' in options) and ('value_imf' in options or 'value_imf_inmirror' in options):
                return options['value_imf'] if 'value_imf' in options else options['value_imf_inmirror']
            if (('value_imap_inmirror' in options or 'value_unctad_inmirror' in options or 'value_imf_inmirror' in options) and 'value_imf' in options):
                return options['value_imf']
            if ('value_imf_inmirror' in options and 'value_imap' in options):
                return options['value_imap']
            if ('value_imf_inmirror' in options and 'value_unctad' in options):
                return options['value_unctad']
            else:
                print(f"Unexpected conflict: {options} ({data_series})")
        else:
            # returning the middle value if more than 2 options (3 or 4)
            return sorted(list(options.values()))[1]
    return value
        

In [227]:
df_mirror = df_ou.merge(df_in, how='outer')
df_mirror=df_mirror.replace({'None':np.nan, ' None':np.nan, 'nan':np.nan}).dropna(subset=['Country', 'Partner Country'], how='any')

In [337]:
df_mirror['value'] = df_mirror.apply(check_consistency, axis=1)

In [350]:
df_mirror.to_csv('../../data/basic_preprocessed/fdi_total.csv')